# Initiation to the DeThermIn workflow

Use the DeThermIn workflow from a Jupyter Notebook!

Let's begin by importing the main module.

In [1]:
import DeThermIn

You can consult the parameters by calling the following script: `DeThermIn.set_params()`. You can otherwise check the dictionary containing the parameters (but you won't have access to the description of the parameters):

In [2]:
DeThermIn.parameters

{'resolution': '2.0',
 'start_date': '2026-06-01',
 'end_date': '2026-08-31',
 'larger_bbox_size_km': '25000',
 'DTC_alpha_1': '0.1',
 'DTC_alpha_2': '0.0001',
 'DTC_sunset_shift': '2.1',
 'fusion_window_size': '15',
 'fusion_alpha_time': '0.1',
 'fusion_alpha_space': '0.5',
 'fusion_k': '0.5',
 'super_resolution_train_size': '0.8',
 'super_resolution_valid_size': '0.2',
 'super_resolution_max_epochs': '20',
 'super_resolution_batch_size': '16',
 'super_resolution_patch_size': '128',
 'super_resolution_learning_rate': '0.001',
 'super_resolution_lambda_ssim': '0.0',
 'downloaded_data_path': '/Volumes/THIBALT/downloaded/',
 'processed_data_path': '/Volumes/THIBALT/processed/',
 'geostationary_data_path': '/Volumes/THIBALT/downloaded/pre-downloaded geostationary data/'}

You should especially look for the parameters `start_date`, `end_date` and `resolution` to orient the workflow towards the date range and final resolution you prefer.

If it is the first use of the workflow, you should also:
- predownload the geostationary data -> `DeThermIn.predownload()` (also if you changed the time range)
- download the geo-file containing the areas available for the workflow -> `DeThermIn.download_available_areas()`

Let's first pre-process the data, which mostly means that we have to download it. One mandatory parameter is a `pandas.GeoDataFrame` corresponding to th area of interest.

In [3]:
from lidar_hd_tools import geodataframe_from_coordinates
gdf = geodataframe_from_coordinates(lat=52.089,lon=5.110, size=1000) # Utrecht!

Here is an example of an area of interest vs the `bbox_size` parameter later used in the pre-processing.

![](_figures/workflow_element_2.png)

In [4]:
ancillary_dc, narrow_swath_dc, geostationary_dc = DeThermIn.pre_process(gdf)

multispectral data already processed.
Computing for a spatial resolution of 2.00 m.
Country: NLD
Status of AppEEARS request: pending


Loading LiDAR data:   0%|          | 0/1 [00:00<?, ?it/s]

Status of AppEEARS request: queued
Status of AppEEARS request: processing
Status of AppEEARS request: Finalizing


Computing shadow: 100%|██████████| 304/304 [01:20<00:00,  3.79it/s]


Computing DHM, SVF, slope gradient, slope aspect...


...

Compressed, 0.09 GB -> 0.08 GB
Getting land cover data...


/opt/miniconda3/envs/DeThermIn_env/lib/python3.13/site-packages/rioxarray/_io.py:1148: NotGeoreferencedWarning: Dataset has no geotransform, gcps, or rpcs. The identity matrix will be returned.
  warnings.warn(str(rio_warning.message), type(rio_warning.message))  # type: ignore


Getting ortho-image...
-> LiDAR workflow is done.
Status of AppEEARS request: done
-> ECOSTRESS workflow is done.
Executing data blending workflow...


Error in sys.excepthook:

Original exception was:
Error in sys.excepthook:

Original exception was:
Error in sys.excepthook:

Original exception was:
Error in sys.excepthook:

Original exception was:
Error in sys.excepthook:

Original exception was:
Error in sys.excepthook:

Original exception was:
Error in sys.excepthook:

Original exception was:


File registered as /Volumes/THIBALT/processed/5_11_52_089_06_01_2026_08_31_2026_ancillary.pkl.
--> Data blending workflow is done.
0.10 GB -> 0.10 GB (/Volumes/THIBALT/processed/5_11_52_089_06_01_2026_08_31_2026_ancillary.pkl)
0.01 GB -> 0.00 GB (/Volumes/THIBALT/processed/5_11_52_089_06_01_2026_08_31_2026_geostationary.pkl)


Now that you launched the pre-processing, you might want to know what is happening.

Simultaneously, data from ECOSTRESS, Sentinel-2 and airborne LiDAR data are downloaded from different APIs. Finally, the geostationary data which has been already pre-downloaded for all the available areas, is clipped to match the greater area of interest.

![](_figures/workflow_element_1.png)
![](_figures/workflow_element_3.png)

The next step allows to fit a Diurnal Temperature Cycle to the geostationary LST.

In [5]:
dtc_fitted_dc = DeThermIn.DTC_fitting(geostationary_dc)

Fitting geostationary to DTC_model cycles: 100%|██████████| 90/90 [01:25<00:00,  1.06it/s]


-> Fitted a Diurnal Temperature Cycle model model to the geostationary data.
0.02 GB -> 0.01 GB (/Volumes/THIBALT/processed/5_11_52_089_06_01_2026_08_31_2026_geostationary-DTC.pkl)


This being done, it is now possible to downscale the parameters of this model to the resolution of the ECOSTRESS LST, thanks to a spatio-temporal unmixing method. This requires to choose a clear-sky day (will be prompted).

![](_figures/workflow_element_4.png)

In [6]:
fusioned_dc = DeThermIn.spatio_temporal_fusion(narrow_swath_dc, dtc_fitted_dc)

[0] 2026-06-20
[1] 2026-06-24
[2] 2026-06-25
[3] 2026-06-26
[4] 2026-07-09
[5] 2026-07-10
[6] 2026-07-12
[7] 2026-07-13
[8] 2026-07-29
[9] 2026-08-08
[10] 2026-08-11
[11] 2026-08-12
[12] 2026-08-13
[13] 2026-08-14
[14] 2026-08-24
-> Proceeding to spatio-temporal unmixing...
Matching coarse and fine datasets...
Processing sunrise LST (1/3)


100%|██████████| 345/345 [03:21<00:00,  1.71it/s]


Processing thermal zenith LST (2/3)


100%|██████████| 345/345 [03:47<00:00,  1.52it/s]


Processing next sunrise LST (3/3)


100%|██████████| 345/345 [03:58<00:00,  1.45it/s]


-> Spatio-temporal fusion workflow is done.
0.06 GB -> 0.04 GB (/Volumes/THIBALT/processed/5_11_52_089_06_01_2026_08_31_2026_fusioned.pkl)


The next and last step is the super-resolution, done thanks to a deep-learning regression. It uses extra-features computed according to the Sun's position at each available timestamp.

![](_figures/workflow_element_6.png)
![](_figures/workflow_element_5.png)

Several models have been trained, differing by the used features for training. Please consult the dedicated folder to learn more. The most sophisticated model can be used with `mode="dynamic"`.

In [7]:
DeThermIn_dc = DeThermIn.super_resolution(ancillary_dc, fusioned_dc, mode="dynamic")

0.14 GB -> 0.14 GB (/Volumes/THIBALT/processed/5_11_52_089_06_01_2026_08_31_2026_blended.pkl)
Getting extra layers (HSV channels, distance grids, ortho-image shadow)...


Computing daily illumination: 100%|██████████| 63/63 [00:00<00:00, 3600.60it/s]
Computing clear sky irradiated energy (last 1 hours): 100%|██████████| 24/24 [00:02<00:00,  8.47it/s]
Computing clear sky irradiated energy (last 2 hours): 100%|██████████| 24/24 [00:04<00:00,  5.57it/s]
Computing clear sky irradiated energy (last 3 hours): 100%|██████████| 24/24 [00:05<00:00,  4.21it/s]
Rebuilding shadows: 100%|██████████| 24/24 [00:00<00:00, 734.08it/s]


Computing irradiance...
0.28 GB -> 0.18 GB (/Volumes/THIBALT/processed/5_11_52_089_06_01_2026_08_31_2026_enriched.pkl)


building DeThermIn product (mode=dynamic): 100%|██████████| 24/24 [00:29<00:00,  1.24s/it]


0.20 GB -> 0.20 GB (/Volumes/THIBALT/processed/5_11_52_089_06_01_2026_08_31_2026_DeThermIn.pkl)


In [8]:
DeThermIn_dc.plot("SR_LST")

You now have the end-product of this workflow! Congrats. If you encountered issues, don't hesitate to report them.